In [1]:
colab = False 

In [2]:
# If using colab
# Takes around 2-3 min

if colab:
    !pip install matplotlib mapclassify folium
    !apt-get install -y osmium-tool
    !pip install "UrbanAccessAnalyzer[osm,plot,h3] @ git+https://github.com/CityScope/UrbanAccessAnalyzer.git"

# Restart notebook after installing this if needed

In [3]:
import os
import time
import pandas as pd
import geopandas as gpd
import os

import osmnx as ox

import UrbanAccessAnalyzer.isochrones as isochrones
import UrbanAccessAnalyzer.graph_processing as graph_processing
import UrbanAccessAnalyzer.osm as osm
import UrbanAccessAnalyzer.utils as utils
import UrbanAccessAnalyzer.h3_utils as h3_utils
import UrbanAccessAnalyzer.population as population
import UrbanAccessAnalyzer.poi_utils as poi_utils
import UrbanAccessAnalyzer.plot_helpers as plot_helpers

import zipfile
import numpy as np

# 1 User inputs

## 1.1 Area of interest (AoI)

In [33]:
# USER INPUT 

city_name = "Alcoy, España"

In [34]:
aoi = utils.get_city_geometry(city_name)
# aoi = gpd.read_file(filepath) # Alternative load your own file
geo_suggestions = utils.get_geographic_suggestions_from_string(city_name,user_agent="app")
geo_suggestions # check that the right city was found

{'country_codes': ['ES'],
 'subdivision_names': ['Alacant / Alicante',
  'Valencian Community',
  "l'Alcoià"],
 'municipalities': ['Alcoi / Alcoy']}

### 1.1.1 OPTIONAL: If you want to draw your own area of interest

Draw here

In [6]:
from ipyleaflet import GeoData
center = aoi.to_crs(4326).union_all().centroid 
m, get_aoi = plot_helpers.ipyleaflet_drawable_map(center=[center.y,center.x])
geo_data = GeoData(
    geo_dataframe=aoi.to_crs(4326),
    style={
        "color": "blue",
        "fillColor": "blue",
        "opacity": 1,
        "fillOpacity": 0,
        "weight": 4,
        "dashArray": "5,5",
    }
)
m.add_layer(geo_data)
m

Map(center=[38.68226836319334, -0.5165876977682137], controls=(ZoomControl(options=['position', 'zoom_in_text'…

Save drawing as area of interest

In [7]:
new_aoi = get_aoi()
if new_aoi is None:
    print("You did not draw anything on the map")
else:
    aoi = new_aoi

aoi

You did not draw anything on the map


,geometry,bbox_west,bbox_south,bbox_east,bbox_north,place_id,osm_type,osm_id,lat,lon,class,type,place_rank,importance,addresstype,name,display_name
0,"POLYGON ((-0.63485 38.6722, -0.63463 38.6703, ...",-0.634851,38.620249,-0.427588,38.743444,291447209,relation,347424,38.698235,-0.474762,boundary,administrative,16,0.556003,town,Alcoi / Alcoy,"Alcoi / Alcoy, l'Alcoià, Alacant / Alicante, V..."


## 1.1.2 Download area 

Use UTM coords and create aoi_download with a buffer of X meters. To avoid boundary effects streets and pois should be downloaded for a larger area.

In [8]:
download_buffer = 1500

aoi = gpd.GeoDataFrame(geometry=[aoi.union_all()],crs=aoi.crs) # Ensure there is only one polygon
aoi = aoi.to_crs(aoi.estimate_utm_crs()) # Convert to utm

aoi_download = aoi.buffer(download_buffer) # Area to do streets and poi requests 

## 1.2 Points of interest (PoI)

### 1.2.1 OPTIONAL: Load your own point of interest data

#### Create your own OpenStreetMap search functions with AI

You can easily create your own OpenStreetMap search function by giving the following prompt to an AI assistant.

##### Example Prompt:

> Modify the following Python function so that it searches for `"hospital"` instead of libraries using an OpenStreetMap Overpass API query.
>
> Ensure the function:
>
> - Keeps the same structure and return behavior
> - Uses the provided bounding box placeholder `{{bbox}}`
> - Returns results transformed to `bounds.crs`
> - Preserves compatibility with the existing `osm.overpass_api_query()` helper
>
> Original function:
>
> ```python
> def libraries(bounds):
>     query = """
>         [out:xml][timeout:25];
>         (
>             node["amenity"="library"]({{bbox}});
>             way["amenity"="library"]({{bbox}});
>             relation["amenity"="library"]({{bbox}});
>         );
>         (._;>;);
>         out body;
>     """
>     pois = osm.overpass_api_query(query, bounds)
>     return pois.to_crs(bounds.crs)
> ```

In [ ]:
# OPTIONAL USER INPUT 
# Example custom OSM query function

def libraries(bounds):
    query = """
        [out:xml][timeout:25];
        (
            node["amenity"="library"]({{bbox}});
            way["amenity"="library"]({{bbox}});
            relation["amenity"="library"]({{bbox}});
        );
        (._;>;);
        out body;
    """
    pois = osm.overpass_api_query(query, bounds)
    return pois.to_crs(bounds.crs)

def gyms(bounds):
    query = """
        [out:xml][timeout:25];
        (
            node["amenity"="gym"]({{bbox}});
            way["amenity"="gym"]({{bbox}});
            relation["amenity"="gym"]({{bbox}});
        );
        (._;>;);
        out body;
    """
    pois = osm.overpass_api_query(query, bounds)
    return pois.to_crs(bounds.crs)


def cinemas(bounds):
    query = """
        [out:xml][timeout:25];
        (
            node["amenity"="cinema"]({{bbox}});
            way["amenity"="cinema"]({{bbox}});
            relation["amenity"="cinema"]({{bbox}});
        );
        (._;>;);
        out body;
    """
    pois = osm.overpass_api_query(query, bounds)
    return pois.to_crs(bounds.crs)

#### Load a custom geofile with PoI data

In [10]:
# OPTIONAL USER INPUT 
# Example custom file loading function
def load_custom_file(bounds):
    gdf = gpd.read_file("path/to/file.gpkg") # Edit here the path to the file you want to load 
    gdf = gdf.to_crs(bounds.crs)
    gdf = gdf[gdf.intersects(bounds.union_all())].reset_index(drop=True)
    return gdf

## 1.2.2 Choose the PoIs for the study

In [ ]:
# USER INPUT 

# All available default functions: 
# osm.green_areas
# osm.bus_stops
# osm.schools 
# osm.healthcare 
# osm.groceries 
# osm.shops
# osm.restaurants
# osm.pharmacies

pois = [
    {
        "type":"school",
        "function":osm.schools,
        "importance":10,
        "max_distance":1000,
        "geometry_type":"Point",
        "icon":"🏫",
    },
    {
        "type":"healthcare",
        "function":osm.healthcare,
        "importance":3,
        "max_distance":2000,
        "geometry_type":"Point",
        "icon":"🏥",
    },
    {
        "type":"groceries",
        "function":osm.groceries,
        "importance":8,
        "max_distance":1500,
        "geometry_type":"Point",
        "icon":"🛒",
    },
    {
        "type":"shops",
        "function":osm.shops,
        "importance":6,
        "max_distance":1500,
        "geometry_type":"Point",
        "icon":"🛍️",
    },
    {
        "type":"restaurant",
        "function":osm.restaurants,
        "importance":7,
        "max_distance":1500,
        "geometry_type":"Point",
        "icon":"🍽️",
    },
    {
        "type":"park",
        "function":osm.green_areas,
        "importance":5,
        "max_distance":1500,
        "geometry_type":"Polygon", # Parks are one of the only pois that should be Polygon
        "icon":"🌳",
    },
    {
        "type":"library",
        "function":libraries,
        "importance":4,
        "max_distance":1500,
        "geometry_type":"Point",
        "icon":"📖",
    },
    {
        "type":"fitness_centre",
        "function":gyms,
        "importance":7,
        "max_distance":1500,
        "geometry_type":"Point",
        "icon":"🏋️‍♂️",
    },
    {
        "type":"cinema",
        "function":cinemas,
        "importance":2,
        "max_distance":2000,
        "geometry_type":"Point",
        "icon":"🎥",
    },
]

### 1.2.3 Basic simluation parameters

In [ ]:
# Number of distance steps for the isochrones (points in the street network reachable in x distance from any point of interest)
n_distance_steps = 5

min_edge_length = 30 # Simplify street graph to avoid edges of less than 'min_edge_length'

h3_resolution = 10 # If you want results in h3 this is the output h3 resolution

max_retries = 3 # For OSM 

show_maps = True # Maps take time to render

Results folder

In [13]:
results_path = os.path.normpath("output")

In [14]:
city_filename = utils.sanitize_filename(city_name)
city_results_path = os.path.join(results_path,city_filename)
os.makedirs(results_path,exist_ok=True)
os.makedirs(city_results_path,exist_ok=True)

In [15]:
poi_path = os.path.normpath(city_results_path+"/points_of_interest.gpkg")
osm_xml_file = os.path.normpath(city_results_path+"/streets.osm")
streets_graph_path = os.path.normpath(city_results_path+"/streets.graphml")
streets_path = os.path.normpath(city_results_path+"/streets.gpkg")
accessibility_streets_path = os.path.normpath(city_results_path+"/accessibility_streets.gpkg")
population_results_path = os.path.normpath(city_results_path+"/population.gpkg")

# 2 Processing

## 2.1 Points of interest

In [ ]:
all_pois = []
for i in range(len(pois)):
    gdf = None
    pois[i]["gdf"] = gdf 
    for attempt in range(max_retries):
        try:
            gdf = pois[i]["function"](aoi_download)
            break
        except Exception as e:
            print(f"Attempt {attempt + 1} failed: {e}")
            if attempt < max_retries - 1:
                time.sleep(2)
            else:
                time.sleep(2)
                continue
                #raise
                
    if gdf is None or len(gdf) == 0:
        continue 
    
    gdf = gdf[gdf.geometry.is_valid].reset_index(drop=True)
    if len(gdf) == 0:
        continue 
        
    if pois[i]["geometry_type"] == "Point":
        gdf = gdf.to_crs(gdf.estimate_utm_crs())
        gdf.geometry = gdf.geometry.centroid
    elif (pois[i]["geometry_type"] != "Polygon") and (pois[i]["geometry_type"] != "LineString"):
        raise Exception(f"Valid values for 'geometry_type' are 'Point' 'Polygon' or 'LineString' but got '{pois[i]["geometry_type"]}'")

    gdf = gdf.to_crs(aoi.crs)
    gdf["type"] = pois[i]["type"]
    gdf["importance"] = pois[i]["importance"]
    gdf["max_distance"] = pois[i]["max_distance"]
    gdf["geometry_type"] = pois[i]["geometry_type"]
    gdf["icon"] = pois[i]["icon"]
    all_pois.append(gdf)
    pois[i]["gdf"] = gdf 
    
all_pois = pd.concat(all_pois)
if "name" in all_pois.columns:
    all_pois["_name_original"] = all_pois["name"].copy()

selected_cols = [
    c for c in all_pois.columns
    if "name" in c
]

all_pois["name"] = (
    all_pois[selected_cols]
    .bfill(axis=1)
    .iloc[:, 0]
)
poi_columns = ["type","name","importance","max_distance","icon","geometry"]

Attempt 1 failed: No valid Overpass API response
Attempt 2 failed: No valid Overpass API response
Attempt 1 failed: No valid Overpass API response


In [17]:
all_pois.to_file(poi_path)

Show all pois on a map

In [18]:
m = None 
if show_maps:
    import folium
    m = plot_helpers.general_map(
        m=m,
        aoi=aoi,
        pois=all_pois[poi_columns],
        poi_column="type",
        poi_color="green",
        poi_icon_column="icon"
    )
    folium.GeoJson(
        aoi_download,
        name="download area",
        style_function=lambda x: {
            "color": "red",
            "weight": 4,
            "dashArray": "5,5",
            "fill": False,
            "opacity": 1.0,
        },
    ).add_to(m)
    m.save(city_results_path+"/points_of_interest_map.html")

m

## 2.2 Street graph

### 2.2.1 Regionwise file and cropping

- Download best regionwise pbf file. (Covers a large area)

- Crop it to cover our area of interest and save it in .osm format

#### OSMIUM

To download the street network needed for the study online, the **osmium** tool is used.  
It is only available for **Linux** and **Mac** (it works in Google Colab too).  

To install, you can either:  

- Visit [osmium-tool website](https://osmcode.org/osmium-tool/)  
- Or run the command:  
```bash
  sudo apt-get install -y osmium-tool
````

Make sure it is added to your `PATH`.

On **Windows**, you can use **conda-forge** to install it.

```bash
  conda install -c conda-forge osmium-tool
````
---

To avoid using **osmium**, you can manually download the data:

1. Go to [OpenStreetMap Export](https://www.openstreetmap.org/export#map=14/40.23633/-3.76084)
2. Select the bounding box containing your area of interest.
3. Click **Export**.
4. Copy the `.osm` file that is downloaded to your project folder.
5. Set the variable `osm_xml_file` to the path where the `.osm` file is located.

In [19]:
# Run only if you have osmium installed or are using colab

# Select what type of street network you want to load
network_filter = osm.osmium_network_filter("walk+bike+primary")
# Download the region pbf file crop it by aoi and convert to osm format
osm.geofabrik_to_osm(
    osm_xml_file,
    input_file=results_path,
    aoi=aoi_download,
    osmium_filter_args=network_filter,
    overwrite=False
)

File 'output/alcoy__spain/streets.osm' already exists. Skipping conversion.


'output/alcoy__spain/streets.osm'

In [20]:
# Manual download 
# osm_xml_file = "path/to/file.osm"

### 2.2.2 Load to osmnx

This way the street network is a networkx graph

In [21]:
# Load
G = ox.graph_from_xml(osm_xml_file)
# Project geometry coordinates to UTM system to allow euclidean meassurements in meters (sorry americans)
G = ox.project_graph(G,to_crs=aoi.estimate_utm_crs())
# Save the graph in graphml format to avoid the slow loading process
ox.save_graphml(G,streets_graph_path)

### 2.2.3 Simplify graph

Edges with length smaler than X meters are deleted and its nodes merged

In [22]:
G = graph_processing.simplify_graph(G,min_edge_length=min_edge_length,min_edge_separation=min_edge_length*2,undirected=True)
# Save the result in graphml format
ox.save_graphml(G,streets_graph_path)

street_edges = ox.graph_to_gdfs(G,nodes=False)
street_edges = street_edges.to_crs(aoi.crs)
street_edges.to_file(streets_path)

In [ ]:
for i in range(len(pois)):
    if "gdf" not in pois[i].keys():
        continue 

    gdf = pois[i]["gdf"]
    if gdf is None or len(gdf) == 0:
        continue

    # explode multi-geometries
    if gdf.geometry.geom_type.str.startswith("Multi").any():
        gdf = gdf.explode(index_parts=False)

    # check if ANY geometry is not Point
    if (gdf.geometry.geom_type != "Point").any():
        poi_points = poi_utils.polygons_to_points(gdf, street_edges)
        gdf = pd.concat([gdf, poi_points], ignore_index=True)

    pois[i]["gdf"] = gdf

## 2.3 Isochrones

In [ ]:
accessiblity_graph = G.copy()
for i in range(len(pois)):
    print(pois[i]["type"])
    distance_steps = np.linspace(
        0,
        pois[i]["max_distance"],
        n_distance_steps + 1
    )[1:]
    distance_steps = list(float(i) for i in distance_steps)
    if "gdf" not in pois[i].keys():
        print("No geometries for type ",pois[i]["type"])
        continue 

    gdf = pois[i]["gdf"]
    if gdf is None or len(gdf) == 0:
        print("No geometries for type ",pois[i]["type"])
        continue 

    gdf = gdf[gdf.geometry.geom_type == "Point"]
    gdf = gdf.reset_index(drop=True)

    accessiblity_graph, osmids = graph_processing.add_points_to_graph(
        gdf,
        accessiblity_graph,
        max_dist=200+min_edge_length, # Maximum distance from point to graph edge to project the point
        min_edge_length=min_edge_length # Minimum edge length after adding the new nodes
    )
    gdf['osmid'] = osmids # Add the ids of the nodes in the graph to points
    gdf["poi_quality"] = 1 
    sorted_steps = sorted(distance_steps)
    n = len(sorted_steps)

    weights = {
        d: [1 - (i / (n - 1)) * (1 - 1/n)] if n > 1 else [1]
        for i, d in enumerate(sorted_steps)
    }

    distance_matrix = pd.DataFrame({
        "poi_quality": [1],
        **weights
    })

    accessiblity_graph = isochrones.graph(
        accessiblity_graph,
        gdf,
        distance_matrix=distance_matrix, # If poi_quality_col is None it could be a list of distances
        poi_quality_col = "poi_quality", # If all points have the same quality this could be None
        min_edge_length = min_edge_length # Do not add new nodes if there will be an edge with less than this length
    )

    accessibility_nodes, accessibility_edges = ox.graph_to_gdfs(accessiblity_graph)
    if pois[i]["geometry_type"] != "Point":
        gdf_polygons = pois[i]["gdf"]
        gdf_polygons = gdf_polygons[gdf_polygons.geometry.geom_type != "Point"]
        if len(gdf_polygons) > 0:
            crs = accessibility_nodes.crs
            accessibility_nodes.loc[accessibility_nodes.intersects(gdf_polygons.to_crs(crs).union_all()),'accessibility'] = 1
            accessibility_edges.loc[accessibility_edges.intersects(gdf_polygons.to_crs(crs).union_all()),'accessibility'] = 1

    accessibility_nodes["accessibility"] = (
        accessibility_nodes["accessibility"]
        .fillna(0)
        .astype(float)
    )
    accessibility_edges["accessibility"] = (
        accessibility_edges["accessibility"]
        .fillna(0)
        .astype(float)
    )
    accessibility_nodes = accessibility_nodes.rename(columns={"accessibility":f"accessibility_{pois[i]['type']}"})
    accessibility_edges = accessibility_edges.rename(columns={"accessibility":f"accessibility_{pois[i]['type']}"})
    accessiblity_graph = ox.graph_from_gdfs(accessibility_nodes,accessibility_edges)


accessibility_nodes, accessibility_edges = ox.graph_to_gdfs(accessiblity_graph)
accessibility_nodes["accessibility"] = 0
accessibility_edges["accessibility"] = 0

weight_sum = 0
for i in range(len(pois)):
    if "gdf" not in pois[i].keys() or pois[i]["gdf"] is None or len(pois[i]["gdf"]) == 0:
        continue 
    
    weight = pois[i]["importance"]
    max_d = pois[i]["max_distance"]
    
    if f"accessibility_{pois[i]['type']}" not in accessibility_nodes.columns:
        continue 

    col = f"accessibility_{pois[i]['type']}"
    accessibility_nodes[col] = accessibility_nodes[col].astype(float)
    accessibility_nodes["accessibility"] += (
        accessibility_nodes[col]
        .fillna(0)
        * weight
    )
    accessibility_nodes[col] = np.where(
        accessibility_nodes[col] == 0,
        None,
        max_d * (1 - accessibility_nodes[col]) + (max_d / n_distance_steps)
    )

    accessibility_edges[col] = accessibility_edges[col].astype(float)
    accessibility_edges["accessibility"] += (
        accessibility_edges[col]
        .astype(float)
        .fillna(0)
        * weight
    )
    accessibility_edges[col] = np.where(
        accessibility_edges[col] == 0,
        None,
        max_d * (1 - accessibility_edges[col]) + (max_d / n_distance_steps)
    )
    weight_sum += weight

accessibility_nodes["accessibility"] /= weight_sum
accessibility_nodes["accessibility"] = accessibility_nodes["accessibility"].fillna(0)
accessibility_edges["accessibility"] /= weight_sum
accessibility_edges["accessibility"] = accessibility_edges["accessibility"].fillna(0)

accessiblity_graph = ox.graph_from_gdfs(accessibility_nodes,accessibility_edges)
accessibility_edges.to_file(accessibility_streets_path)

school


100%|██████████| 5/5 [00:00<00:00,  8.21it/s]


groceries


100%|██████████| 5/5 [00:00<00:00,  6.73it/s]


park


100%|██████████| 5/5 [00:00<00:00,  5.58it/s]


library


100%|██████████| 5/5 [00:01<00:00,  4.70it/s]


#### Lets visualize the results on a map

### 2.3.2 Convert to H3

In [25]:
access_h3_df = h3_utils.from_gdf(
    accessibility_edges,
    resolution=h3_resolution,
    columns=['accessibility'],
    contain="overlap",
    method="max",
    buffer=10
)

access_h3_df

,accessibility
h3_cell,
8a3956324807fff,0.0
8a3956324827fff,0.0
8a395632482ffff,0.0
8a3956324837fff,0.0
8a3956324867fff,0.0
...,...
8a3956af6d8ffff,0.0
8a3956af6d97fff,0.0
8a3956af6d9ffff,0.0


See everything on a map

In [26]:
m = None
if show_maps:
    m = plot_helpers.general_map(
        aoi=aoi,
        pois=all_pois[poi_columns],
        gdfs=[access_h3_df,accessibility_edges],
        cmap="RdYlGn",
        column="accessibility",
        poi_column="type",
        poi_color="green",
        poi_icon_column="icon"
    )
    m.save(city_results_path+"/access_map.html")
m

## 3 Population or census data

### 3.1 Download Worldpop tif file

- One file for every country
- 100m pixel size
- tif format
- available from 2000 to 2030
- gender and age

In [27]:
population_file = population.download_worldpop_population(
    aoi_download,
    2025,
    folder=results_path,
    resolution="100m",
)

Raster population path output/esp_pop_2025_CN_100m_R2025A_v1.tif exists. Skipping download...


In [28]:
pop_h3_df = h3_utils.from_raster(population_file,aoi=aoi_download,resolution=h3_resolution)
pop_h3_df = pop_h3_df.rename(columns={'value':'population'})

### 3.2 Assign level of service to each population cell

In [29]:
results_h3_df = access_h3_df.merge(pop_h3_df,left_index=True,right_index=True,how='outer')
results_h3_df = h3_utils.to_gdf(results_h3_df).to_crs(aoi.crs)
results_h3_df = results_h3_df[results_h3_df.intersects(aoi.union_all())]
results_h3_df.to_file(population_results_path)
results_h3_df

,accessibility,population,geometry
h3_cell,,,
8a3956320807fff,NaN,1.713273,"POLYGON ((719024.492 4279510.474, 718956.49 42..."
8a3956320817fff,NaN,0.091063,"POLYGON ((718946.327 4279404.99, 718878.325 42..."
8a3956320827fff,NaN,0.675916,"POLYGON ((718976.814 4279636.37, 718908.811 42..."
8a3956320837fff,NaN,0.189190,"POLYGON ((718898.649 4279530.886, 718830.646 4..."
8a39563208affff,NaN,0.000669,"POLYGON ((718994.005 4279279.095, 718926.003 4..."
...,...,...,...
8a3956af6d97fff,0.0,0.619707,"POLYGON ((717253.872 4289487.349, 717185.861 4..."
8a3956af6d9ffff,0.0,1.550860,"POLYGON ((717379.732 4289466.87, 717311.722 42..."
8a3956af6da7fff,0.0,1.759559,"POLYGON ((717284.352 4289718.71, 717216.341 42..."


In [30]:
m = None 
if show_maps:
    pop_gdf_points = results_h3_df.copy()
    pop_gdf_points.geometry = pop_gdf_points.geometry.centroid
    pop_gdf_points = pop_gdf_points.dropna(subset=['population'])
    pop_gdf_points = pop_gdf_points[pop_gdf_points['population'] > 1]
    m = plot_helpers.general_map(
        aoi=aoi,
        pois=all_pois[poi_columns],
        gdfs=[pop_gdf_points],
        cmap="RdYlGn",
        column="accessibility",
        size_column="population",
        poi_column="type",
        poi_color="green",
        poi_icon_column="icon"
    )
    m.save(city_results_path+"/population_map.html")
m

# 4 Statistics

In [31]:
# Create bins 0.0 → 1.0
bins = np.linspace(0, 1, 11)

# Create labels using upper bound of each bin
labels = [round(b, 1) for b in bins[1:]]

# Group WITHOUT modifying original dataframe
stats_df = (
    results_h3_df
    .groupby(
        pd.cut(
            results_h3_df["accessibility"],
            bins=bins,
            labels=labels,
            include_lowest=True
        ),
        observed=False
    )["population"]
    .sum()
    .reset_index()
    .rename(columns={"accessibility": "accessibility"})
)

# Ensure proper sorting (numeric order, not string order)
stats_df["accessibility"] = stats_df["accessibility"].astype(float)
stats_df = stats_df.sort_values("accessibility", ascending=False)

# Total population
total_population = stats_df["population"].sum()

# Add total row
stats_df = pd.concat([
    stats_df,
    pd.DataFrame([{
        "accessibility": "total population",
        "population": total_population
    }])
], ignore_index=True)

# Percentages
stats_df["population %"] = (
    stats_df["population"] * 100 / total_population
).round(2)

# Final formatting
stats_df["population"] = stats_df["population"].round(0).astype(int)

# Export
stats_df.to_csv(city_results_path + "/stats.csv", index=False)
stats_df

,accessibility,population,population %
0,1.0,1415,2.54
1,0.9,4554,8.18
2,0.8,7868,14.14
3,0.7,7181,12.91
4,0.6,7745,13.92
5,0.5,5840,10.49
6,0.4,9232,16.59
7,0.3,3873,6.96
8,0.2,4023,7.23
9,0.1,3912,7.03


In [ ]:
if colab:
    !zip -r /content/results.zip "{city_results_path}" # For colab. Export the results folder as zip.

In [ ]:
if colab:
    !zip -r /content/output.zip "{results_path}" # For colab. Export the output folder as zip.

Important files:

- points_of_interest.gpkg all points of interest
- streets.gpkg Has the street geometry as lines (all streets)
- accessibility.gpkg Has the street geometry as lines with the accessibility score (only streets with score > 0)
- population.gpkg Is a grid with population and level of service
- stats.csv Population statistics